# Results 2 — stable synthetic pairs (feature-frequency analysis)

Inputs: `base_features_<dt>.csv` and `synthetic_features_<dt>.csv` from `../M2_loco_crc_pipeline/results/<dt>/` (selection frequency of every feature in the final *All Features + Synthetic* RF across the 14 LOCO folds).
A pair is **stable** if its synthetic feature was selected in ≥ 80 % of folds and more often than either constituent (Methods *Feature frequency analysis*). Output: `final_synthetic_features_table.csv` (the 'N stable pairs', 'from the combined model', '0 % individual frequency' and hub counts quoted in the Results text), consumed by `effect_sizes.ipynb` (Figure 3, Supplementary Table 4) and `../R3_pair_transformations/transformation_preference.ipynb` (Figure 4, Supplementary Table 6).


In [1]:
import pandas as pd
import numpy as np
import matplotlib.pyplot as plt
import seaborn as sns
import os

# Set style
sns.set_style("whitegrid")
plt.rcParams['figure.figsize'] = (12, 6)

# Load feature files from main_code.ipynb output 
# Process only data types that have been run (for now, only TAXA)

data_types = ['taxa', 'functions', 'combined']
input_dirs = {
    'taxa': '../M2_loco_crc_pipeline/results/taxa',
    'functions': '../M2_loco_crc_pipeline/results/functions',
    'combined': '../M2_loco_crc_pipeline/results/combined'
}

# Load data only for types that exist
data = {}
for data_type in data_types:
    input_dir = input_dirs[data_type]
    raw_file = f'{input_dir}/base_features_{data_type}.csv'
    synth_file = f'{input_dir}/synthetic_features_{data_type}.csv'
    
    if os.path.exists(raw_file) and os.path.exists(synth_file):
        data[data_type] = {
            'raw': pd.read_csv(raw_file),
            'synthetic': pd.read_csv(synth_file)
        }
        print(f"{data_type.capitalize()} - Raw: {len(data[data_type]['raw'])} features, Synthetic: {len(data[data_type]['synthetic'])} features")
    else:
        print(f"{data_type.capitalize()}: Files not found, skipping...")

if not data:
    raise ValueError("No data files found! Please run main_code.ipynb first.")

print(f"\nNote: Using output from main_code.ipynb (consensus pairs in >= 6 of 10 MDFS runs per fold; one RF per fold)")
print(f"Processing: {list(data.keys())}")

Taxa - Raw: 126 features, Synthetic: 906 features
Functions - Raw: 215 features, Synthetic: 1027 features
Combined - Raw: 21 features, Synthetic: 1209 features

Note: Using output from main_code.ipynb (consensus pairs in >= 6 of 10 MDFS runs per fold; one RF per fold)
Processing: ['taxa', 'functions', 'combined']


In [2]:
# Define thresholds
SYNTHETIC_THRESHOLD = 80.0  # Pair must be selected in >= 80% of LOCO folds to be "stable"
INDIVIDUAL_LOW_THRESHOLD = 20.0  # < 20% for low individual features

print(f"Thresholds:")
print(f"  Synthetic pair stability: selected in >= {SYNTHETIC_THRESHOLD}% of LOCO folds")
print(f"  Individual feature 'low': selected in < {INDIVIDUAL_LOW_THRESHOLD}% of folds")
print()

# Process each data type separately
all_results = []

for data_type in data_types:
    print("="*80)
    print(f"PROCESSING {data_type.upper()}")
    print("="*80)
    
    raw_df = data[data_type]['raw']
    synthetic_df = data[data_type]['synthetic']
    
    # Identify synthetic features with >= 80% selection rate across folds
    synth_high = synthetic_df[synthetic_df['Selection %'] >= SYNTHETIC_THRESHOLD].copy()
    synth_high = synth_high.sort_values('Selection %', ascending=False)
    
    # Identify individual features with low selection rate (< 20%)
    individual_low = raw_df[raw_df['Selection %'] < INDIVIDUAL_LOW_THRESHOLD].copy()
    individual_low = individual_low.sort_values('Selection %', ascending=True)
    
    print(f"\nStable synthetic pairs (selected in >= {SYNTHETIC_THRESHOLD}% of folds): {len(synth_high)}")
    print(f"Low-frequency individual features (< {INDIVIDUAL_LOW_THRESHOLD}% of folds): {len(individual_low)}")
    
    # Add synthetic features to results
    for idx, row in synth_high.iterrows():
        all_results.append({
            'Data Type': data_type,
            'Feature': row['Feature'],
            'Feature Type': 'Synthetic',
            'Selection %': row['Selection %'],
            'Selection Count': row['Selection Count']
        })
    
    # Add individual features to results
    for idx, row in individual_low.iterrows():
        all_results.append({
            'Data Type': data_type,
            'Feature': row['Feature'],
            'Feature Type': 'Individual',
            'Selection %': row['Selection %'],
            'Selection Count': row['Selection Count']
        })
    
    # Store for component analysis
    data[data_type]['synth_high'] = synth_high
    data[data_type]['individual_low'] = individual_low

print("\n" + "="*80)
print("SUMMARY")
print("="*80)
print(f"Total features identified: {len(all_results)}")
result_df = pd.DataFrame(all_results)
print(f"\nBreakdown by data type:")
print(result_df.groupby('Data Type').size())
print(f"\nBreakdown by feature type:")
print(result_df.groupby('Feature Type').size())
print("="*80)

Thresholds:
  Synthetic pair stability: selected in >= 80.0% of LOCO folds
  Individual feature 'low': selected in < 20.0% of folds

PROCESSING TAXA

Stable synthetic pairs (selected in >= 80.0% of folds): 242
Low-frequency individual features (< 20.0% of folds): 27
PROCESSING FUNCTIONS

Stable synthetic pairs (selected in >= 80.0% of folds): 65
Low-frequency individual features (< 20.0% of folds): 48
PROCESSING COMBINED

Stable synthetic pairs (selected in >= 80.0% of folds): 188
Low-frequency individual features (< 20.0% of folds): 8

SUMMARY
Total features identified: 578

Breakdown by data type:
Data Type
combined     196
functions    113
taxa         269
dtype: int64

Breakdown by feature type:
Feature Type
Individual     83
Synthetic     495
dtype: int64


In [3]:
# Analyze component features of synthetic features (>= 80% prevalence)
# Check if individual features from synthetic pairs appear in raw features list

def analyze_synthetic_components(synthetic_df, raw_df, data_type_name):
    """Analyze component features of synthetic features."""
    results = []
    
    # Create a dictionary for quick lookup of raw feature prevalence
    raw_feature_dict = dict(zip(raw_df['Feature'], raw_df['Selection %']))
    
    for idx, row in synthetic_df.iterrows():
        synthetic_feature = row['Feature']
        synthetic_prevalence = row['Selection %']
        
        # Remove prefix (LR_, GM_)
        feature_name = synthetic_feature
        for prefix in ['LR_', 'GM_']:
            if feature_name.startswith(prefix):
                feature_name = feature_name[len(prefix):]
                break
        
        # Split by '__' to get component features
        if '__' in feature_name:
            feature1, feature2 = feature_name.split('__', 1)
            
            # Check feature1
            feature1_prevalence = raw_feature_dict.get(feature1, 0.0)
            results.append({
                'Synthetic Feature': synthetic_feature,
                'Synthetic Prevalence': synthetic_prevalence,
                'Component Feature': feature1,
                'Component Prevalence': feature1_prevalence,
                'Feature Type': 'Feature 1'
            })
            
            # Check feature2
            feature2_prevalence = raw_feature_dict.get(feature2, 0.0)
            results.append({
                'Synthetic Feature': synthetic_feature,
                'Synthetic Prevalence': synthetic_prevalence,
                'Component Feature': feature2,
                'Component Prevalence': feature2_prevalence,
                'Feature Type': 'Feature 2'
            })
        else:
            # If no '__' found, skip or handle differently
            print(f"Warning: Could not split feature: {synthetic_feature}")
    
    result_df = pd.DataFrame(results)
    
    # Group by synthetic feature to show both components together
    # Sort by synthetic prevalence (descending), then by component prevalence (ascending)
    result_df = result_df.sort_values(['Synthetic Prevalence', 'Component Prevalence'], 
                                     ascending=[False, True])
    
    return result_df

In [4]:
# Perform component analysis for all three data types
all_component_analyses = {}

for data_type in data_types:
    print("="*80)
    print(f"COMPONENT FEATURES ANALYSIS - {data_type.upper()}")
    print("(From main_code.ipynb - 100% Feature Intersection Approach)")
    print("="*80)
    
    synth_high = data[data_type]['synth_high']
    raw_df = data[data_type]['raw']
    
    if len(synth_high) > 0:
        component_analysis = analyze_synthetic_components(synth_high, raw_df, data_type.capitalize())
        all_component_analyses[data_type] = component_analysis
        
        print(f"\nTotal component features analyzed: {len(component_analysis)}")
        print(f"\nNote: Each synthetic feature has TWO component features (Feature 1 and Feature 2)")
        print(f"      Component Prevalence = 0.0 means the feature was NOT selected in any fold")
        print(f"      Component Prevalence > 0 means the feature WAS selected in some folds")
        print(f"\nComponent features grouped by synthetic feature:\n")
        
        # Group and display by synthetic feature for better readability
        for synth_feat in component_analysis['Synthetic Feature'].unique():
            synth_data = component_analysis[component_analysis['Synthetic Feature'] == synth_feat]
            print(f"\nSynthetic Feature: {synth_feat}")
            print(f"  Synthetic Prevalence: {synth_data['Synthetic Prevalence'].iloc[0]:.2f}%")
            print(f"  Components:")
            for _, row in synth_data.iterrows():
                comp_prev = row['Component Prevalence']
                comp_name = row['Component Feature']
                comp_type = row['Feature Type']
                status = "NOT selected" if comp_prev == 0.0 else f"selected in {comp_prev:.2f}% of folds"
                print(f"    {comp_type}: {comp_name} - {status}")
        
        print(f"\n\nFull table (sorted by synthetic prevalence, then component prevalence):\n")
        print(component_analysis.to_string(index=False))
    else:
        print(f"\nNo synthetic features with >= {SYNTHETIC_THRESHOLD}% prevalence to analyze.")
    print("="*80)

COMPONENT FEATURES ANALYSIS - TAXA
(From main_code.ipynb - 100% Feature Intersection Approach)

Total component features analyzed: 484

Note: Each synthetic feature has TWO component features (Feature 1 and Feature 2)
      Component Prevalence = 0.0 means the feature was NOT selected in any fold
      Component Prevalence > 0 means the feature WAS selected in some folds

Component features grouped by synthetic feature:


Synthetic Feature: GM_Peptostreptococcus_anaerobius__Peptostreptococcus_stomatis
  Synthetic Prevalence: 100.00%
  Components:
    Feature 1: Peptostreptococcus_anaerobius - NOT selected
    Feature 2: Peptostreptococcus_stomatis - selected in 57.14% of folds

Synthetic Feature: GM_Eikenella_corrodens__Parvimonas_micra
  Synthetic Prevalence: 100.00%
  Components:
    Feature 1: Eikenella_corrodens - NOT selected
    Feature 2: Parvimonas_micra - selected in 21.43% of folds

Synthetic Feature: GM_Fusobacterium_nucleatum__Lactobacillus_crispatus
  Synthetic Prevalence:

In [5]:
# =============================================================================
# FINAL TABLE: Stable synthetic pairs with prevalence gain
# =============================================================================
# Interpretation:
#   In the MDFS framework, a base feature gains information gain (IG) about the
#   target when conditioned on a contributing feature. When this 2D interaction
#   is encoded as a synthetic feature (log-ratio or geometric mean), its
#   PREVALENCE across LOCO folds measures how consistently the model relies on
#   it. A high pair prevalence with low individual prevalence confirms that the
#   base feature's IG arises specifically through its interaction with the
#   contributing feature — neither carries sufficient signal in isolation.
#
# Terminology:
#   Pair Prevalence     = % of LOCO folds where the synthetic pair was selected
#   Base feature        = the feature gaining IG (lower individual prevalence)
#   Contributing feature = the feature providing IG context (higher individual prev)
#   Prevalence Gain     = Pair Prevalence − mean(Base Prev, Contrib Prev)
# =============================================================================

N_LOCO_FOLDS = 14

print("="*80)
print("STABLE SYNTHETIC PAIRS — PREVALENCE GAIN ANALYSIS")
print("="*80)
print(f"\nCriteria:")
print(f"  1. Pair prevalence >= {SYNTHETIC_THRESHOLD}% (selected in >= {int(SYNTHETIC_THRESHOLD * N_LOCO_FOLDS / 100)}/{N_LOCO_FOLDS} LOCO folds)")
print(f"  2. Pair prevalence exceeds BOTH individual feature prevalences")
print(f"  3. Positive prevalence gain (pair is more prevalent than expected from individuals)")
print(f"\nInterpretation:")
print(f"  The base feature gains information gain (IG) thanks to the contributing feature.")
print(f"  High pair prevalence with low individual prevalences confirms the interaction")
print(f"  is genuinely informative — the model selects the pair, not the features alone.")
print("\n" + "="*80 + "\n")

# Create the initial results dataframe
final_results_df = pd.DataFrame(all_results)

# Process synthetic features: remove pairing type prefix and extract component features
def process_synthetic_feature(row, raw_df):
    """Process synthetic feature to remove prefix and extract component info."""
    feature = row['Feature']
    
    # Remove prefix (LR_, GM_)
    feature_name = feature
    pairing_type = None
    for prefix in ['LR_', 'GM_']:
        if feature_name.startswith(prefix):
            pairing_type = prefix.rstrip('_')
            feature_name = feature_name[len(prefix):]
            break
    
    # Split by '__' to get component features
    if '__' in feature_name:
        feature1, feature2 = feature_name.split('__', 1)
        
        # Get prevalences from raw_df (same model)
        raw_feature_dict = dict(zip(raw_df['Feature'], raw_df['Selection %']))
        feature1_prev = raw_feature_dict.get(feature1, 0.0)
        feature2_prev = raw_feature_dict.get(feature2, 0.0)
        
        return {
            'Feature': feature_name,
            'Feature1': feature1,
            'Feature1_Selection%': feature1_prev,
            'Feature2': feature2,
            'Feature2_Selection%': feature2_prev,
        }
    else:
        return {
            'Feature': feature_name,
            'Feature1': None,
            'Feature1_Selection%': None,
            'Feature2': None,
            'Feature2_Selection%': None,
        }

# Process each row
processed_rows = []
for idx, row in final_results_df.iterrows():
    if row['Feature Type'] == 'Synthetic':
        raw_df = data[row['Data Type']]['raw']
        processed = process_synthetic_feature(row, raw_df)
        new_row = row.copy()
        new_row['Feature'] = processed['Feature']
        new_row['Feature1'] = processed['Feature1']
        new_row['Feature1_Selection%'] = processed['Feature1_Selection%']
        new_row['Feature2'] = processed['Feature2']
        new_row['Feature2_Selection%'] = processed['Feature2_Selection%']
        processed_rows.append(new_row)
    else:
        new_row = row.copy()
        new_row['Feature1'] = None
        new_row['Feature1_Selection%'] = None
        new_row['Feature2'] = None
        new_row['Feature2_Selection%'] = None
        processed_rows.append(new_row)

final_results_df = pd.DataFrame(processed_rows)

# Fill NaN values with 0 for gain calculation
final_results_df['Feature1_Selection%'] = final_results_df['Feature1_Selection%'].fillna(0.0)
final_results_df['Feature2_Selection%'] = final_results_df['Feature2_Selection%'].fillna(0.0)

# Calculate Prevalence Gain:
# = Pair Prevalence (Selection %) - mean(Feature1_Selection%, Feature2_Selection%)
# Measures how much the pair's prevalence exceeds what individual features achieve alone
def calculate_prevalence_gain(row):
    if row['Feature Type'] == 'Synthetic':
        pair_prev = row['Selection %']
        avg_individual = (row['Feature1_Selection%'] + row['Feature2_Selection%']) / 2.0
        return pair_prev - avg_individual
    return None

final_results_df['Selection % Gain'] = final_results_df.apply(calculate_prevalence_gain, axis=1)

# Reorder columns
column_order = ['Data Type', 'Feature Type', 'Feature', 'Feature1', 'Feature1_Selection%', 
                'Feature2', 'Feature2_Selection%', 'Selection %', 'Selection % Gain', 'Selection Count']
final_results_df = final_results_df[column_order]

# Deduplicate (LR_ and GM_ variants of same pair)
final_results_df = final_results_df.drop_duplicates(subset=['Data Type', 'Feature Type', 'Feature'], keep='first')

# Apply filters:
# 1. Pair prevalence >= threshold (stable pair)
# 2. Positive prevalence gain
# 3. Pair prevalence > both individual prevalences
final_results_df = final_results_df[
    (final_results_df['Feature Type'] == 'Synthetic') & 
    (final_results_df['Selection %'] >= SYNTHETIC_THRESHOLD) &
    (final_results_df['Selection % Gain'] > 0) &
    (final_results_df['Selection %'] > final_results_df['Feature1_Selection%']) &
    (final_results_df['Selection %'] > final_results_df['Feature2_Selection%'])
].copy()

# Sort by prevalence gain (descending)
final_results_df = final_results_df.sort_values(['Selection % Gain', 'Selection %'], 
                                                ascending=[False, False])

# --- Pretty-print results ---
print(f"{'No.':<4} {'Model':<10} {'Pair Prevalence':<18} {'Base Prev':<12} {'Contrib Prev':<14} {'Prevalence Gain':<16}")
print("-" * 76)
for i, (_, r) in enumerate(final_results_df.iterrows(), 1):
    pair_prev = f"{r['Selection %']:.1f}% ({int(r['Selection Count'])}/{N_LOCO_FOLDS})"
    # The feature with lower individual prevalence is the base (gaining IG)
    # The feature with higher individual prevalence is the contributor (providing IG)
    f1_prev = r['Feature1_Selection%']
    f2_prev = r['Feature2_Selection%']
    base_prev = f"{min(f1_prev, f2_prev):.1f}%"
    contrib_prev = f"{max(f1_prev, f2_prev):.1f}%"
    gain = f"+{r['Selection % Gain']:.1f} pp"
    
    print(f"{i:<4} {r['Data Type']:<10} {pair_prev:<18} {base_prev:<12} {contrib_prev:<14} {gain:<16}")
    
    # Identify base vs contributing feature
    if f1_prev <= f2_prev:
        base_name = str(r['Feature1']).replace('_', ' ')
        contrib_name = str(r['Feature2']).replace('_', ' ')
    else:
        base_name = str(r['Feature2']).replace('_', ' ')
        contrib_name = str(r['Feature1']).replace('_', ' ')
    print(f"     Base (gaining IG):    {base_name}")
    print(f"     Contrib (providing IG): {contrib_name}")
    print()

print("="*80)
print(f"Total pairs meeting criteria: {len(final_results_df)}")
print(f"  By model: {dict(final_results_df.groupby('Data Type').size())}")
print("="*80)

# =============================================================================
# HUB FEATURE ANALYSIS
# =============================================================================
# Identify features that appear repeatedly across multiple stable pairs.
# A "hub" gaining IG from many partners carries latent disease signal that
# only becomes detectable in combination. A "hub" providing IG to many
# partners acts as a contextualizer — its presence unlocks the IG of
# features that would otherwise be undetectable individually.

print("\n\n" + "="*80)
print("HUB FEATURE ANALYSIS")
print("="*80)
print("\nFeatures appearing most frequently as components of stable pairs.")
print("'Base' = feature gaining IG from the partner (lower individual prevalence)")
print("'Contrib' = feature providing IG context (higher individual prevalence)\n")

# Collect all component features from the final table
from collections import Counter, defaultdict

hub_counter = Counter()
hub_as_base = Counter()
hub_as_contrib = Counter()
hub_prev_vals = defaultdict(list)  # actual individual prevalences per occurrence
hub_models = defaultdict(set)

for _, r in final_results_df.iterrows():
    f1 = r['Feature1']
    f2 = r['Feature2']
    f1_prev = r['Feature1_Selection%']
    f2_prev = r['Feature2_Selection%']
    model = r['Data Type']

    hub_counter[f1] += 1
    hub_counter[f2] += 1
    hub_prev_vals[f1].append(f1_prev)
    hub_prev_vals[f2].append(f2_prev)
    hub_models[f1].add(model)
    hub_models[f2].add(model)

    if f1_prev <= f2_prev:
        hub_as_base[f1] += 1
        hub_as_contrib[f2] += 1
    else:
        hub_as_base[f2] += 1
        hub_as_contrib[f1] += 1

# Show top hubs (appearing in >= 3 pairs)
MIN_HUB_COUNT = 3
hub_df = pd.DataFrame([
    {
        'Feature': feat,
        'Total Pairs': count,
        'As Base (gaining IG)': hub_as_base.get(feat, 0),
        'As Contributor (providing IG)': hub_as_contrib.get(feat, 0),
        'Individual Prevalence': np.mean(hub_prev_vals[feat]),
        'Models': ', '.join(sorted(hub_models[feat])),
    }
    for feat, count in hub_counter.most_common()
    if count >= MIN_HUB_COUNT
])

if len(hub_df) > 0:
    hub_df = hub_df.sort_values('Total Pairs', ascending=False)
    print(f"{'Feature':<50} {'Pairs':<6} {'Base':<6} {'Contrib':<8} {'Indiv Prev':<11} {'Models'}")
    print("-" * 100)
    for _, h in hub_df.iterrows():
        feat_disp = str(h['Feature']).replace('_', ' ')
        if len(feat_disp) > 48:
            feat_disp = feat_disp[:47] + '…'
        print(f"{feat_disp:<50} {int(h['Total Pairs']):<6} {int(h['As Base (gaining IG)']):<6} {int(h['As Contributor (providing IG)']):<8} {h['Individual Prevalence']:.1f}%{'':<5} {h['Models']}")

    print(f"\nTotal hub features (in >= {MIN_HUB_COUNT} pairs): {len(hub_df)}")

    # Pair-level statistics
    both_zero = len(final_results_df[
        (final_results_df['Feature1_Selection%'] == 0) &
        (final_results_df['Feature2_Selection%'] == 0)
    ])
    at_least_one_zero = len(final_results_df[
        (final_results_df['Feature1_Selection%'] == 0) |
        (final_results_df['Feature2_Selection%'] == 0)
    ])
    print(f"\nPairs where BOTH features have 0% individual prevalence: {both_zero}/{len(final_results_df)}")
    print(f"Pairs where at least one feature has 0% individual prevalence: {at_least_one_zero}/{len(final_results_df)}")

    # Features predominantly gaining IG
    mainly_base = hub_df[hub_df['As Base (gaining IG)'] > hub_df['As Contributor (providing IG)']]
    mainly_contrib = hub_df[hub_df['As Contributor (providing IG)'] > hub_df['As Base (gaining IG)']]

    if len(mainly_base) > 0:
        print(f"\nFeatures predominantly GAINING IG from partners (base role):")
        print(f"  These carry latent disease signal detectable only through interaction.\n")
        for _, h in mainly_base.iterrows():
            print(f"  - {h['Feature'].replace('_', ' ')}")
            print(f"    base in {int(h['As Base (gaining IG)'])}/{int(h['Total Pairs'])} pairs | indiv. prevalence = {h['Individual Prevalence']:.1f}% | {h['Models']}")

    if len(mainly_contrib) > 0:
        print(f"\nFeatures predominantly PROVIDING IG to partners (contributor role):")
        print(f"  These act as contextualizers — their presence unlocks the IG of base features.\n")
        for _, h in mainly_contrib.iterrows():
            print(f"  - {h['Feature'].replace('_', ' ')}")
            print(f"    contributor in {int(h['As Contributor (providing IG)'])}/{int(h['Total Pairs'])} pairs | indiv. prevalence = {h['Individual Prevalence']:.1f}% | {h['Models']}")

print("\n" + "="*80)

# Save the final table for downstream analysis
output_file = 'final_synthetic_features_table.csv'
final_results_df.to_csv(output_file, index=False)
print(f"\nSaved to: {output_file}")
print(f"  This file can be imported by consistent_mdfs_markers_downstream.ipynb")

STABLE SYNTHETIC PAIRS — PREVALENCE GAIN ANALYSIS

Criteria:
  1. Pair prevalence >= 80.0% (selected in >= 11/14 LOCO folds)
  2. Pair prevalence exceeds BOTH individual feature prevalences
  3. Positive prevalence gain (pair is more prevalent than expected from individuals)

Interpretation:
  The base feature gains information gain (IG) thanks to the contributing feature.
  High pair prevalence with low individual prevalences confirms the interaction
  is genuinely informative — the model selects the pair, not the features alone.




No.  Model      Pair Prevalence    Base Prev    Contrib Prev   Prevalence Gain 
----------------------------------------------------------------------------
1    functions  100.0% (14/14)     0.0%         0.0%           +100.0 pp       
     Base (gaining IG):    P163-PWY: L-lysine fermentation to acetate and butanoate
     Contrib (providing IG): REDCITCYC: TCA cycle VI (Helicobacter)

2    functions  100.0% (14/14)     0.0%         0.0%           +100.0 pp       
     Base (gaining IG):    ORNDEG-PWY: superpathway of ornithine degradation
     Contrib (providing IG): P163-PWY: L-lysine fermentation to acetate and butanoate

3    functions  100.0% (14/14)     0.0%         0.0%           +100.0 pp       
     Base (gaining IG):    ORNDEG-PWY: superpathway of ornithine degradation
     Contrib (providing IG): P161-PWY: acetylene degradation (anaerobic)

4    functions  100.0% (14/14)     0.0%         0.0%           +100.0 pp       
     Base (gaining IG):    ORNDEG-PWY: superpathway of 

In [6]:
# --- Compact cohort-validation plot for FINAL synthetic features table ---
# Uses `final_results_df` (built above) which already applies:
# - Selection % >= SYNTHETIC_THRESHOLD (default 80%)
# - positive Selection % Gain
# - synthetic Selection % > both component Selection %
#
# This cell validates each selected synthetic pair across cohorts (CRC vs Control):
# - effect size: rank-biserial correlation (rbc) from Mann–Whitney U
# - per-cohort p-values, BH-FDR within each pair
# - compact small-multiples figure (paper-friendly)

from pathlib import Path


def _bh_fdr(pvals):
    p = np.asarray(pvals, dtype=float)
    q = np.full_like(p, np.nan, dtype=float)
    ok = np.isfinite(p)
    if ok.sum() == 0:
        return q

    p_ok = p[ok]
    m = p_ok.size
    order = np.argsort(p_ok)
    ranked = p_ok[order]

    q_ranked = ranked * m / (np.arange(1, m + 1))
    q_ranked = np.minimum.accumulate(q_ranked[::-1])[::-1]
    q_ranked = np.clip(q_ranked, 0, 1)

    q_ok = np.empty_like(p_ok)
    q_ok[order] = q_ranked
    q[ok] = q_ok
    return q


def _cohort_stems_for_data_type(data_type: str):
    base = Path("..") / "M1_data_preparation" / "prepared_data"
    paths = sorted(base.glob(f"X_*_{data_type}.tsv"))
    suffix = f"_{data_type}.tsv"
    out = []
    for p in paths:
        name = p.name
        if not name.startswith("X_") or not name.endswith(suffix):
            continue
        out.append(name[len("X_") : -len(suffix)])
    return out


def load_X_y_for_cohort(cohort_stem: str, data_type: str):
    base = Path("..") / "M1_data_preparation" / "prepared_data"
    X_path = base / f"X_{cohort_stem}_{data_type}.tsv"
    y_path = base / f"y_{cohort_stem}_{data_type}.tsv"

    # Fallback: any y for cohort
    if not y_path.exists():
        cands = sorted(base.glob(f"y_{cohort_stem}_*.tsv"))
        if cands:
            y_path = cands[0]

    if not X_path.exists() or not y_path.exists():
        return None, None

    X = pd.read_csv(X_path, sep="\t", index_col=0)
    y_df = pd.read_csv(y_path, sep="\t", index_col=0)
    if "Study condition" not in y_df.columns:
        return None, None

    # Normalize (relative abundance)
    X = X.div(X.sum(axis=1), axis=0)

    y = y_df["Study condition"].astype(int)

    # Align
    common = X.index.intersection(y.index)
    X = X.loc[common]
    y = y.loc[common]

    return X, y


def find_matching_feature_name(feature_name, available_columns):
    # exact
    if feature_name in available_columns:
        return feature_name

    # functions/pathways: use prefix before ':'
    if isinstance(feature_name, str) and ':' in feature_name:
        pathway_id = feature_name.split(':')[0].strip()
        if pathway_id in available_columns:
            return pathway_id
        for col in available_columns:
            if col.startswith(pathway_id) or col == pathway_id:
                return col

    # case-insensitive
    if isinstance(feature_name, str):
        fl = feature_name.lower()
        for col in available_columns:
            if str(col).lower() == fl:
                return col

    # partial
    if isinstance(feature_name, str):
        for col in available_columns:
            c = str(col)
            if len(feature_name) > 5 and len(c) > 5 and (feature_name in c or c in feature_name):
                return col

    return None


def compute_synthetic_feature_from_X(X: pd.DataFrame, feature1: str, feature2: str, feature_type: str, epsilon: float = 1e-9):
    f1 = find_matching_feature_name(feature1, X.columns)
    f2 = find_matching_feature_name(feature2, X.columns)
    if f1 is None or f2 is None:
        return None

    a = X[f1].to_numpy(dtype=float)
    b = X[f2].to_numpy(dtype=float)

    if feature_type == "LR":
        return np.log((a + epsilon) / (b + epsilon))
    if feature_type == "GM":
        return np.sqrt((a + epsilon) * (b + epsilon))
    return None


def _compute_rbc_and_p(disease_vals: np.ndarray, health_vals: np.ndarray):
    from scipy.stats import mannwhitneyu

    disease_vals = np.asarray(disease_vals, dtype=float)
    health_vals = np.asarray(health_vals, dtype=float)
    disease_vals = disease_vals[np.isfinite(disease_vals)]
    health_vals = health_vals[np.isfinite(health_vals)]

    n_crc = len(disease_vals)
    n_ctrl = len(health_vals)
    if n_crc == 0 or n_ctrl == 0:
        return np.nan, np.nan, n_crc, n_ctrl

    try:
        U, p = mannwhitneyu(disease_vals, health_vals, alternative="two-sided")
    except Exception:
        return np.nan, 1.0, n_crc, n_ctrl

    denom = n_crc * n_ctrl
    rbc = (2 * U / denom - 1) if denom > 0 else np.nan
    return float(rbc), float(p), n_crc, n_ctrl


def _shorten_pwy(s):
    if s is None:
        return "", None
    s = str(s)
    if ":" in s:
        prefix = s.split(":", 1)[0]
        if "PWY" in prefix:
            return prefix, s
    return s, None


def _truncate(s, max_len=44):
    if s is None:
        return ""
    s = str(s)
    return s if len(s) <= max_len else (s[: max_len - 1] + "…")


def compute_pair_table_for_final_row(row, try_types=("LR", "GM")):
    data_type = row["Data Type"]
    f1 = row["Feature1"]
    f2 = row["Feature2"]

    cohorts = _cohort_stems_for_data_type(data_type)

    best = None
    for t in try_types:
        rows = []
        for cohort in cohorts:
            X, y = load_X_y_for_cohort(cohort, data_type)
            if X is None or y is None:
                continue

            synth = compute_synthetic_feature_from_X(X, f1, f2, t)
            if synth is None:
                continue

            disease_mask = (y == 0)
            health_mask = (y == 1)
            dvals = np.asarray(synth)[disease_mask.to_numpy()]
            hvals = np.asarray(synth)[health_mask.to_numpy()]

            rbc, p, n_crc, n_ctrl = _compute_rbc_and_p(dvals, hvals)
            if not np.isfinite(rbc) or not np.isfinite(p) or n_crc == 0 or n_ctrl == 0:
                continue

            rows.append(
                {
                    "cohort": cohort,
                    "cohort_short": str(cohort).replace("Public_study__", "").replace("This_study_", ""),
                    "rbc": rbc,
                    "p": p,
                    "n_crc": n_crc,
                    "n_ctrl": n_ctrl,
                }
            )

        df = pd.DataFrame(rows)
        if len(df) == 0:
            continue

        df["q"] = _bh_fdr(df["p"].values)
        # pick best by most cohorts
        cand = (t, df)
        if best is None or len(df) > len(best[1]):
            best = cand

    if best is None:
        return None, pd.DataFrame()

    t, df = best
    df = df.sort_values("q", ascending=True).reset_index(drop=True)
    return t, df


# ----------------- knobs -----------------
# Choose how many of the FINAL table pairs to plot
# (sorted by Selection % Gain then Selection %)
MAX_PAIRS_TO_PLOT = None  # e.g. 12
N_COLS = 3
FIG_DPI = 300

PANEL_W = 4.35
PANEL_H = 3.05
TITLE_FS = 12
PARAM_FS = 10
TICK_FS = 10
PANEL_LABEL_FS = 14
SUP_FS = 14

# ----------------- select pairs -----------------
if "Selection % Gain" in final_results_df.columns:
    pairs_df = final_results_df.sort_values(["Selection % Gain", "Selection %"], ascending=[False, False]).copy()
else:
    pairs_df = final_results_df.copy()

if MAX_PAIRS_TO_PLOT is not None:
    pairs_df = pairs_df.head(MAX_PAIRS_TO_PLOT).reset_index(drop=True)

pairs_df = pairs_df.reset_index(drop=True)

# ----------------- compute panels -----------------
panels = []
all_rbc = []
caption_lines = []

for i, r in pairs_df.iterrows():
    feature_type, df = compute_pair_table_for_final_row(r)
    label = f"{chr(ord('a') + i)})"

    f1_raw = r.get("Feature1")
    f2_raw = r.get("Feature2")

    caption_lines.append(f"{label} {r.get('Data Type')} | {feature_type}: {f1_raw} × {f2_raw}")

    if len(df) > 0:
        all_rbc.extend(df["rbc"].values.tolist())

    panels.append((label, r, feature_type, df))

if len(all_rbc) == 0:
    print("⚠ No cohort-level results available for the selected final-table pairs.")
else:
    xlim = max(0.25, float(np.nanmax(np.abs(all_rbc))))
    xlim = min(1.0, xlim)

    from matplotlib.gridspec import GridSpec

    n_panels = len(panels)
    nrows = int(np.ceil(n_panels / N_COLS))

    fig = plt.figure(figsize=(PANEL_W * N_COLS, PANEL_H * nrows), dpi=FIG_DPI)
    gs = GridSpec(nrows, N_COLS * 2, figure=fig, wspace=0.45, hspace=0.95)

    for i, (label, row, feature_type, df) in enumerate(panels):
        rr = i // N_COLS
        cc = i % N_COLS
        n_in_row = min(N_COLS, n_panels - rr * N_COLS)
        offset = (N_COLS - n_in_row)
        start_col = offset + cc * 2
        ax = fig.add_subplot(gs[rr, start_col : start_col + 2])

        data_type = row["Data Type"]
        f1_raw = row["Feature1"]
        f2_raw = row["Feature2"]
        f1_short, _f1_full = _shorten_pwy(f1_raw)
        f2_short, _f2_full = _shorten_pwy(f2_raw)
        f1_disp = _truncate(f1_short)
        f2_disp = _truncate(f2_short)

        if len(df) == 0:
            ax.text(0.5, 0.5, "No data", ha="center", va="center", transform=ax.transAxes, fontsize=TITLE_FS)
            ax.set_axis_off()
            continue

        y = np.arange(len(df))
        colors = np.where(df["q"].values < 0.05, "tab:red", "tab:blue")
        ax.scatter(df["rbc"].values, y, c=colors, s=32, alpha=0.97, edgecolors="black", linewidth=0.35)
        ax.axvline(0, color="black", linestyle="--", linewidth=1.0, alpha=0.75)

        if len(df) <= 6:
            ax.set_yticks(y)
            ax.set_yticklabels(df["cohort_short"].tolist(), fontsize=TICK_FS)
        else:
            ax.set_yticks([])

        ax.invert_yaxis()
        ax.set_xlim(-xlim, xlim)
        ax.grid(axis="x", alpha=0.25)
        ax.tick_params(axis="x", labelsize=TICK_FS)

        ax.text(0.01, 0.98, label, transform=ax.transAxes, ha="left", va="top", fontsize=PANEL_LABEL_FS, fontweight="bold")

        ax.set_title(f"{data_type} | {feature_type} | n={len(df)}", fontsize=TITLE_FS, fontweight="bold", y=1.18, pad=0)
        ax.text(0.5, 1.06, f"{f1_disp} × {f2_disp}", transform=ax.transAxes, ha="center", va="bottom", fontsize=PARAM_FS, clip_on=False)

    fig.supxlabel("Effect size: rank-biserial r (CRC vs Control)", fontsize=SUP_FS, fontweight="bold")
    fig.supylabel("Cohorts (labels omitted if many)", fontsize=SUP_FS, fontweight="bold")
    fig.suptitle(f"FINAL synthetic features (Selection% ≥ {SYNTHETIC_THRESHOLD}, gain > 0): cohort validation", fontsize=SUP_FS + 1, fontweight="bold", y=1.02)
    plt.savefig("stable_pairs_cohort_validation_overview.png", dpi=150, bbox_inches="tight")
    plt.show()

    print("Legend:")
    print("  dot color: red = cohort significant after BH-FDR within that pair (q<0.05); blue = not significant")

    print("\nCaption (full feature names):")
    for line in caption_lines:
        print("- " + line)


/var/folders/14/cbbyp9td0gl7qft267hmvqs00000gn/T/ipykernel_31562/3068462157.py:331: UserWarning: Glyph 127 () missing from font(s) Arial.
  plt.savefig("stable_pairs_cohort_validation_overview.png", dpi=150, bbox_inches="tight")
/var/folders/14/cbbyp9td0gl7qft267hmvqs00000gn/T/ipykernel_31562/3068462157.py:331: UserWarning: Glyph 128 (\x80) missing from font(s) Arial.
  plt.savefig("stable_pairs_cohort_validation_overview.png", dpi=150, bbox_inches="tight")
/var/folders/14/cbbyp9td0gl7qft267hmvqs00000gn/T/ipykernel_31562/3068462157.py:331: UserWarning: Glyph 129 (\x81) missing from font(s) Arial.
  plt.savefig("stable_pairs_cohort_validation_overview.png", dpi=150, bbox_inches="tight")
/var/folders/14/cbbyp9td0gl7qft267hmvqs00000gn/T/ipykernel_31562/3068462157.py:331: UserWarning: Glyph 130 (\x82) missing from font(s) Arial.
  plt.savefig("stable_pairs_cohort_validation_overview.png", dpi=150, bbox_inches="tight")
/var/folders/14/cbbyp9td0gl7qft267hmvqs00000gn/T/ipykernel_31562/306846

/Users/kizie/miniconda3/lib/python3.10/site-packages/IPython/core/pylabtools.py:170: UserWarning: Glyph 127 () missing from font(s) Arial.
  fig.canvas.print_figure(bytes_io, **kw)
/Users/kizie/miniconda3/lib/python3.10/site-packages/IPython/core/pylabtools.py:170: UserWarning: Glyph 128 (\x80) missing from font(s) Arial.
  fig.canvas.print_figure(bytes_io, **kw)
/Users/kizie/miniconda3/lib/python3.10/site-packages/IPython/core/pylabtools.py:170: UserWarning: Glyph 129 (\x81) missing from font(s) Arial.
  fig.canvas.print_figure(bytes_io, **kw)
/Users/kizie/miniconda3/lib/python3.10/site-packages/IPython/core/pylabtools.py:170: UserWarning: Glyph 130 (\x82) missing from font(s) Arial.
  fig.canvas.print_figure(bytes_io, **kw)
/Users/kizie/miniconda3/lib/python3.10/site-packages/IPython/core/pylabtools.py:170: UserWarning: Glyph 131 (\x83) missing from font(s) Arial.
  fig.canvas.print_figure(bytes_io, **kw)
/Users/kizie/miniconda3/lib/python3.10/site-packages/IPython/core/pylabtools.p

Legend:
  dot color: red = cohort significant after BH-FDR within that pair (q<0.05); blue = not significant

Caption (full feature names):
- a) functions | LR: P163-PWY:_L-lysine_fermentation_to_acetate_and_butanoate × REDCITCYC:_TCA_cycle_VI_(Helicobacter)
- b) functions | LR: ORNDEG-PWY:_superpathway_of_ornithine_degradation × P163-PWY:_L-lysine_fermentation_to_acetate_and_butanoate
- c) functions | LR: ORNDEG-PWY:_superpathway_of_ornithine_degradation × P161-PWY:_acetylene_degradation_(anaerobic)
- d) functions | LR: ORNDEG-PWY:_superpathway_of_ornithine_degradation × PWY-6167:_flavin_biosynthesis_II_(archaea)
- e) functions | LR: ORNDEG-PWY:_superpathway_of_ornithine_degradation × PWY4LZ-257:_superpathway_of_fermentation_(Chlamydomonas_reinhardtii)
- f) combined | LR: Peptostreptococcus_stomatis × Streptococcus_infantis
- g) combined | LR: Peptostreptococcus_anaerobius × Peptostreptococcus_stomatis
- h) combined | LR: Dialister_pneumosintes × Peptostreptococcus_stomatis
- i) combi